[![Text: CC BY-SA 4.0](https://img.shields.io/badge/text-CC%20BY--SA%204.0-lightgrey.svg)](https://creativecommons.org/licenses/by-sa/4.0/)
[![Code: MIT](https://img.shields.io/badge/code-MIT-yellow.svg)](https://opensource.org/license/mit)

This notebook is part of course materials for CS 545: Machine Learning at
Colorado State University. These notebooks are based on the PyTorch version of
[Dive into Deep Learning](https://d2l.ai) by Aston Zhang, Zachary C. Lipton,
Mu Li and Alexander J. Smola, used under
[CC BY-SA 4.0](https://creativecommons.org/licenses/by-sa/4.0/) and heavily
modified by [Asa Ben-Hur](https://www.cs.colostate.edu/~asa/) with
[Claude](https://claude.com) AI. The text is released under
[CC BY-SA 4.0](https://creativecommons.org/licenses/by-sa/4.0/); the code is
released under the [MIT license](https://opensource.org/license/mit).

# Attention:  building meaning from context

The previous notebook established three things about the transformer: it works (matching the BiLSTM on sentiment), it is blind to word order, and each of its layers computes a matrix of *attention weights*.  The notebooks that follow will open the box and describe the attention operation precisely.

This one has no equations and trains no model.  Its job is to answer the following question: *what is attention for?*  The one-sentence version:

> The embedding layer assigns each word a *fixed* vector, the same in every sentence.  Attention updates those vectors, layer by layer, so that each word's representation comes to reflect the *context* it appears in.

The rest of the notebook is designed to give you an intuition of how attention does that.  Everything drawn here is a schematic — a hand-built 2D "meaning space," not a trained model, chosen so the geometry is legible.  The real thing lives in hundreds of dimensions and is learned from data.

In [1]:
try:
    from matplotlib_inline.backend_inline import set_matplotlib_formats
    set_matplotlib_formats('svg')
except ImportError:
    pass

import numpy as np
import torch
from torch import nn
import matplotlib.pyplot as plt
from matplotlib.animation import FuncAnimation
from matplotlib.collections import LineCollection
from matplotlib.colors import to_rgb
from matplotlib.patches import FancyBboxPatch
from IPython.display import HTML

# render animations as inline HTML players
plt.rcParams['animation.html'] = 'jshtml'
plt.rcParams['animation.embed_limit'] = 60  # MB
plt.rcParams['animation.frame_format'] = 'jpeg'  # much smaller than png

# ---- shared look for the animations in this notebook ----
DPI = 80               # figure resolution; also sets the on-screen size
PAPER = '#fbfaf6'      # background
INK = '#3a3a3a'        # main text
MUTED = '#8a8a8a'      # secondary text
MOLE = '#ee7d1f'       # the word we follow
CLS_COL = '#7a5cc4'    # the <cls> token
REGION_COLORS = {'CHEMISTRY': '#2f76d2', 'ANIMAL': '#249a6b',
                 'ESPIONAGE': '#cf3f4f'}


def ease(t):
    """Smooth start and stop for motion (t in [0, 1])."""
    t = np.clip(t, 0.0, 1.0)
    return t * t * (3 - 2 * t)


def blank_axes(ax, xlim, ylim):
    """Clear an axes and give it the shared look: no ticks, no frame."""
    ax.clear()
    ax.set_facecolor(PAPER)
    ax.set_xlim(*xlim)
    ax.set_ylim(*ylim)
    ax.set_xticks([])
    ax.set_yticks([])
    for spine in ax.spines.values():
        spine.set_visible(False)


def region_image(regions, xlim, ylim, sigma=1.15, res=150):
    """Soft glowing blobs, one per semantic region, as an RGBA image.

    Computed once and redrawn every frame with imshow.
    """
    xs = np.linspace(*xlim, res)
    ys = np.linspace(*ylim, res)
    X, Y = np.meshgrid(xs, ys)
    img = np.zeros((res, res, 4))
    img[..., :3] = to_rgb(PAPER)
    for name, center in regions.items():
        d2 = (X - center[0]) ** 2 + (Y - center[1]) ** 2
        a = 0.32 * np.exp(-d2 / (2 * sigma ** 2))
        rgb = np.array(to_rgb(REGION_COLORS[name]))
        # paint this blob over what is already there
        img[..., :3] = img[..., :3] * (1 - a[..., None]) + rgb * a[..., None]
    img[..., 3] = 1.0
    return img


def draw_regions(ax, regions, img, xlim, ylim, label_dy=1.25):
    """The meaning-space background: glowing regions and their names."""
    ax.imshow(img, extent=(*xlim, *ylim), origin='lower', zorder=0,
              interpolation='bilinear', aspect='auto')
    for name, c in regions.items():
        ax.text(c[0], c[1] + label_dy, name, color=REGION_COLORS[name],
                ha='center', va='bottom', fontsize=8.5, fontweight='bold',
                alpha=0.75, zorder=1)


def glow_dot(ax, xy, color, size=300, glow=1.0, zorder=6):
    """A dot with a soft halo; glow scales the halo (0 = no halo)."""
    for scale, alpha in [(4.0, 0.08), (2.0, 0.16)]:
        ax.scatter(*xy, s=size * scale, color=color, alpha=alpha * glow,
                   linewidths=0, zorder=zorder - 1)
    ax.scatter(*xy, s=size, color=color, edgecolor='white', linewidths=1.6,
               zorder=zorder)


def glow_line(ax, p0, p1, color, width, alpha=1.0, zorder=2):
    """A line with a soft halo around it."""
    xs, ys = [p0[0], p1[0]], [p0[1], p1[1]]
    ax.plot(xs, ys, color=color, lw=width * 3.2, alpha=0.10 * alpha,
            solid_capstyle='round', zorder=zorder)
    ax.plot(xs, ys, color=color, lw=width, alpha=0.85 * alpha,
            solid_capstyle='round', zorder=zorder + 0.1)


def particles(ax, path, n, phase, color, size=14, zorder=4):
    """n dots streaming along path (an array of points) from start to end.

    phase in [0, 1) shifts the dots along, so animating phase makes them flow.
    """
    if n <= 0:
        return
    fracs = (np.arange(n) / n + phase) % 1.0
    idx = (fracs * (len(path) - 1)).astype(int)
    pts = path[idx]
    # dots fade in after leaving the start and fade out on arrival
    alpha = 0.9 * np.minimum(1, 5 * fracs) * np.minimum(1, 8 * (1 - fracs))
    ax.scatter(pts[:, 0], pts[:, 1], s=size, color=color, alpha=alpha,
               linewidths=0, zorder=zorder)


def straight_path(p0, p1, n=60):
    """n points on the segment from p0 to p1."""
    t = np.linspace(0, 1, n)[:, None]
    return (1 - t) * np.asarray(p0) + t * np.asarray(p1)


def curved_path(p0, p1, n=60):
    """n points on a smooth S-curve from p0 (below) to p1 (above)."""
    p0, p1 = np.asarray(p0, float), np.asarray(p1, float)
    mid = (p1[1] - p0[1]) * 0.4
    c0, c1 = p0 + [0, mid], p1 - [0, mid]
    t = np.linspace(0, 1, n)[:, None]
    return ((1 - t) ** 3 * p0 + 3 * (1 - t) ** 2 * t * c0
            + 3 * (1 - t) * t ** 2 * c1 + t ** 3 * p1)


def fading_trail(ax, pts, color, width=2.5, zorder=3):
    """A path drawn more faintly the older it is."""
    pts = np.asarray(pts)
    if len(pts) < 2:
        return
    segs = np.stack([pts[:-1], pts[1:]], axis=1)
    alphas = np.linspace(0.08, 0.7, len(segs))
    rgba = [(*to_rgb(color), a) for a in alphas]
    ax.add_collection(LineCollection(segs, colors=rgba, linewidths=width,
                                     capstyle='round', zorder=zorder))


def word_pill(ax, xy, text, color=INK, face='white', alpha=1.0, fs=9,
              zorder=5, **kw):
    """A word in a rounded box."""
    ax.text(*xy, text, ha='center', va='center', fontsize=fs, color=color,
            alpha=alpha, zorder=zorder,
            bbox=dict(boxstyle='round,pad=0.35,rounding_size=0.6',
                      facecolor=face, edgecolor=color, linewidth=0.9,
                      alpha=alpha), **kw)


def colored_sentence(ax, words, colors, y=1.03, fs=11.5, bold=()):
    """Write a sentence centered above an axes, one color per word."""
    fig = ax.figure
    renderer = fig.canvas.get_renderer()
    texts, widths = [], []
    for w, c in zip(words, colors):
        t = ax.text(0, y, w, transform=ax.transAxes, fontsize=fs, color=c,
                    va='bottom', ha='left',
                    fontweight='bold' if w in bold else 'normal')
        bb = t.get_window_extent(renderer=renderer)
        texts.append(t)
        widths.append(bb.width / ax.bbox.width)   # in axes units
    space = 0.012 * fs / 11.5
    x = 0.5 - (sum(widths) + space * (len(words) - 1)) / 2
    for t, w in zip(texts, widths):
        t.set_x(x)
        x += w + space

## Input embeddings:  One word, one vector

Our input tokens are converted to vectors using an embedding layer.  Those vectors are fixed, regardless of context.  In the following, we give three "sentences" that share the word *mole* used three different ways:

In [2]:
torch.manual_seed(0)
vocab = {w: i for i, w in enumerate(
    ['<unk>', 'mole', 'avogadro', 'grams', 'burrowed', 'garden',
     'spy', 'agency', 'the', 'a', 'of', 'number'])}
embedding = nn.Embedding(len(vocab), 8)   # 8-dimensional toy embeddings

sentences = [
    ['a', 'mole', 'of', 'avogadro', 'number'],   # chemistry
    ['the', 'mole', 'burrowed', 'garden'],        # animal
    ['the', 'mole', 'spy', 'agency'],             # espionage
]

for sent in sentences:
    ids = torch.tensor([vocab[w] for w in sent])
    vecs = embedding(ids)
    mole_vec = vecs[sent.index('mole')]
    print(f'{" ".join(sent):32s}  mole -> {mole_vec[:4].detach().numpy().round(3)} ...')

a mole of avogadro number         mole -> [ 0.322 -1.263  0.35   0.308] ...
the mole burrowed garden          mole -> [ 0.322 -1.263  0.35   0.308] ...
the mole spy agency               mole -> [ 0.322 -1.263  0.35   0.308] ...


The vector for *mole* is identical in all three sentences.  Yet the three moles could hardly be more different: a unit of $6\times10^{23}$ particles, a small burrowing mammal, an infiltrating agent.  A single fixed vector cannot be a good representation of all three at once.

This is the deficiency attention exists to fix.  We want the vector *at the mole position* to end up somewhere different depending on the company it keeps — pulled toward "chemistry" among *avogadro* and *grams*, toward "animal" among *burrowed* and *garden*.  That is what the next picture shows.

## The idea: context refines meaning

The following figure demonstrates the role of attention - to move the embedding of a vector to a region in the embedding space that better represents its meaning in the sentence. Each attention layer nudges the mole vector toward the region its neighbors imply, and stacking layers refines the estimate.

In [3]:
# --- a hand-built 2D "meaning space" (illustration, not a trained model) ---
regions = {'CHEMISTRY': np.array([3.2, 2.3]),
           'ANIMAL':    np.array([3.0, -2.4]),
           'ESPIONAGE': np.array([-3.2, 1.6])}
context_pos = {'avogadro': np.array([2.2, 2.7]), 'grams': np.array([4.0, 1.6]),
               'burrowed': np.array([2.3, -2.9]), 'garden': np.array([3.8, -1.8]),
               'agency': np.array([-2.0, 2.4]), 'spy': np.array([-4.0, 0.8])}
demo = [("one mole contains avogadro's number of grams", ['avogadro', 'grams'],
         'CHEMISTRY'),
        ("the mole burrowed under the garden", ['burrowed', 'garden'],
         'ANIMAL'),
        ("the mole inside the agency was a foreign spy", ['agency', 'spy'],
         'ESPIONAGE')]
mole_start = np.array([0.2, 0.15])
n_layers = 3
XLIM, YLIM = (-5.2, 5.6), (-4, 4)
bg = region_image(regions, XLIM, YLIM)

# timeline, in frames: pause, then one move per layer, then a hold
fps = 10
INTRO, MOVE, HOLD = 8, 14, 14
per = INTRO + n_layers * MOVE + HOLD
FINALE = 28


def trajectory(ctx):
    """mole position per layer: move a fraction toward the mean of context."""
    pts, p = [mole_start.copy()], mole_start.copy()
    for _ in range(n_layers):
        p = p + 0.45 * (np.mean([context_pos[w] for w in ctx], axis=0) - p)
        pts.append(p.copy())
    return pts


trajs = [trajectory(ctx) for _, ctx, _ in demo]


def mole_state(traj, local):
    """Where mole is, which layer it is on, and the path it has travelled."""
    if local < INTRO:
        return traj[0], 0, [traj[0]], False
    if local < INTRO + n_layers * MOVE:
        layer, sub = divmod(local - INTRO, MOVE)
        a, b = traj[layer], traj[layer + 1]
        pos = a + ease(sub / MOVE) * (b - a)
        # sample the path so the trail is smooth
        path = list(traj[:layer + 1]) + [pos]
        return pos, layer + 1, path, True
    return traj[-1], n_layers, list(traj), False


def draw_sentence_title(ax, sent, ctx, region):
    words = sent.split()
    colors, bold = [], ['mole']
    for w in words:
        base = w.split("'")[0]          # avogadro's -> avogadro
        if w == 'mole':
            colors.append(MOLE)
        elif base in ctx:
            colors.append(REGION_COLORS[region])
            bold.append(w)
        else:
            colors.append(MUTED)
    colored_sentence(ax, words, colors, bold=bold)


def layer_dots(ax, layer):
    """'attention layer k' with a row of progress dots."""
    label = ('context-free embedding' if layer == 0
             else f'after attention layer {layer}')
    ax.text(0.5, 0.045, label, transform=ax.transAxes, ha='center',
            fontsize=9.5, color=INK)
    for k in range(n_layers):
        ax.scatter(0.47 + 0.03 * k, 0.015, s=28, transform=ax.transAxes,
                   color=MOLE if k < layer else '#dddddd', zorder=7,
                   clip_on=False)


fig, ax = plt.subplots(figsize=(7, 5.6), dpi=DPI)
fig.patch.set_facecolor(PAPER)
fig.subplots_adjust(left=0.01, right=0.99, bottom=0.01, top=0.9)


def frame(f):
    blank_axes(ax, XLIM, YLIM)
    draw_regions(ax, regions, bg, XLIM, YLIM)
    glow_dot(ax, mole_start, '#bbbbbb', size=60, glow=0, zorder=3)

    if f >= per * len(demo):                        # finale: all three paths
        t = ease((f - per * len(demo)) / (FINALE * 0.6))
        for traj in trajs:
            path = np.array(traj)
            end = path[0] + t * (path[-1] - path[0])
            fading_trail(ax, straight_path(path[0], end, 40), MOLE, width=3)
            glow_dot(ax, path[-1], MOLE, size=200, glow=t)
        ax.text(mole_start[0] - 0.3, mole_start[1] - 0.45, 'same start',
                ha='center', fontsize=9, color=MUTED, style='italic')
        ax.text(0.5, 1.03, 'one word, one starting vector, three meanings',
                transform=ax.transAxes, ha='center', va='bottom',
                fontsize=12, color=INK, fontweight='bold')
        return []

    s, local = divmod(f, per)
    sent, ctx, region = demo[s]
    col = REGION_COLORS[region]
    pos, layer, path, moving = mole_state(trajs[s], local)

    # endpoints reached in earlier sentences stay as faint ghosts
    for traj in trajs[:s]:
        ax.scatter(*traj[-1], s=140, facecolor='none', edgecolor=MOLE,
                   linewidths=1.2, linestyle=(0, (2, 2)), alpha=0.6, zorder=3)

    # context words pull on mole: lines brighten while it moves
    for w in ctx:
        wp = context_pos[w]
        if layer > 0:
            glow_line(ax, wp, pos, col, 2.2, alpha=0.9 if moving else 0.45)
            if moving:
                particles(ax, straight_path(wp, pos), 5, (f % 15) / 15, col,
                          size=18)
        glow_dot(ax, wp, col, size=55, glow=0.6, zorder=5)
        # label on the far side of the word, away from where mole ends up
        away = wp - trajs[s][-1]
        away = 0.5 * away / np.linalg.norm(away)
        word_pill(ax, wp + away, w, color=col, fs=8.5)

    # mole's route so far, with a marker at each completed layer
    dense = []
    for a, b in zip(path[:-1], path[1:]):
        dense += list(straight_path(a, b, 15))
    fading_trail(ax, dense or path, MOLE)
    for k, p in enumerate(trajs[s][1:layer + 1 if not moving else layer], 1):
        ax.scatter(*p, s=90, color='white', edgecolor=MOLE, linewidths=1.4,
                   zorder=5)
        ax.text(*p, str(k), ha='center', va='center', fontsize=6.5,
                color=MOLE, fontweight='bold', zorder=6)

    glow_dot(ax, pos, MOLE, size=280, glow=1.0 if moving else 0.6, zorder=8)
    # label beside the route (perpendicular to it, on the lower side)
    d = trajs[s][-1] - mole_start
    side = np.array([d[1], -d[0]]) / np.linalg.norm(d)
    if side[1] > 0:
        side = -side
    ax.text(*(pos + 0.5 * side), 'mole', ha='center', va='center',
            fontsize=11, fontweight='bold', color=MOLE, zorder=9)

    draw_sentence_title(ax, sent, ctx, region)
    layer_dots(ax, layer)
    return []


anim = FuncAnimation(fig, frame, frames=per * len(demo) + FINALE, blit=False)
html = HTML(anim.to_jshtml(fps=fps)); plt.close(fig); html

Same word, same starting embedding vector.  Each words arrives at a different location in "meaning space" according to the neighbors in the sentence.  Two key ideas:

* **Representation becomes contextual.**  The output vector at a position is no longer the word's generic embedding; it has moved to reflect a particular sentence.  This is the sense in which a transformer "understands" a word in context.
* **Depth refines.**  One layer gets *mole* into the right neighborhood; further layers can sharpen it (and, in a real model, resolve subtler things — which noun a pronoun refers to, whether "bank" is a verb or a noun).  Stacking attention layers is stacking rounds of contextual refinement.

Next is *how* a token knows which way to move.

## The mechanism: a weighted pull from every other word

How does the mole vector "know" to head toward chemistry?  It doesn't decide in advance; it *looks at the other words and moves a little toward each*, pulling hardest toward the ones most relevant to it.  Its updated vector is a **weighted average** of the surrounding vectors: relevant neighbors get large weights, irrelevant ones get nearly zero.  The animation below fixes a focus word and shows the pull from each other word, with arrow thickness proportional to the weight.

In [4]:
# words of a sentence, placed for legibility (again: an illustration)
toks = ['the', 'mole', 'burrowed', 'under', 'the', 'garden']
pos2 = {i: np.array(p) for i, p in enumerate(
    [(-4, 1.2), (-2, -0.6), (0, 1.4), (1.4, -1.1), (3, 1.0), (4.4, -0.7)])}
focus = 1  # 'mole'
# hand-set "relevance" of each word to the focus (large for burrowed/garden)
weights = np.array([0.05, 0.10, 0.42, 0.06, 0.05, 0.32])
target = sum(weights[i] * pos2[i] for i in pos2)  # weighted average
PULL = '#2f76d2'

# timeline, in frames: the pulls appear, then mole moves, then a hold
fps2 = 10
GROW, FLOW, HOLD2 = 18, 30, 16
XLIM2, YLIM2 = (-5.5, 5.5), (-2.3, 2.5)

fig, (ax, axb) = plt.subplots(2, 1, figsize=(7.2, 5.0), dpi=DPI,
                              gridspec_kw=dict(height_ratios=[3, 1.1]))
fig.patch.set_facecolor(PAPER)
fig.subplots_adjust(left=0.02, right=0.98, top=0.9, bottom=0.07, hspace=0.12)


def tint(w):
    """Blend from grey (irrelevant) to the pull color (relevant)."""
    a = min(1.0, w / 0.4)
    return tuple((1 - a) * np.array(to_rgb(MUTED)) + a * np.array(to_rgb(PULL)))


def frame2(f):
    reveal = ease(f / GROW)                      # pulls appear
    slide = ease((f - GROW) / FLOW)              # mole moves to the average
    flowing = GROW <= f < GROW + FLOW
    fp = pos2[focus] + slide * (target - pos2[focus])

    # ---- top: the pulls in meaning space ----
    blank_axes(ax, XLIM2, YLIM2)
    start = pos2[focus]
    if slide > 0:                                # where mole started
        ax.scatter(*start, s=260, facecolor='none', edgecolor=MOLE,
                   linewidths=1.2, linestyle=(0, (2, 2)), alpha=0.7, zorder=3)
        ax.text(start[0], start[1] - 0.45, 'embedding', ha='center',
                fontsize=8, color=MOLE, alpha=0.8 * slide, style='italic')
        fading_trail(ax, straight_path(start, fp, 30), MOLE, width=2.5)
    for i in pos2:
        if i == focus:
            continue
        w = weights[i]
        tip = pos2[i] + reveal * (fp - pos2[i])  # line grows toward mole
        glow_line(ax, pos2[i], tip, PULL, 0.6 + 14 * w, alpha=0.35 + w)
        if flowing:
            particles(ax, straight_path(pos2[i], fp), 2 + round(20 * w),
                      (f % 15) / 15, PULL, size=6 + 40 * w)
        word_pill(ax, pos2[i], toks[i], color=tint(w), fs=9.5)
    glow_dot(ax, fp, MOLE, size=320, glow=1.0 if flowing else 0.6, zorder=8)
    ax.text(fp[0], fp[1] + 0.45, 'mole', ha='center', fontsize=11,
            fontweight='bold', color=MOLE, zorder=9,
            bbox=dict(boxstyle='round,pad=0.15', facecolor=PAPER,
                      edgecolor='none', alpha=0.85))
    ax.text(0.5, 1.04, 'each word pulls on "mole"; thicker = more relevant',
            transform=ax.transAxes, ha='center', va='bottom', fontsize=12,
            color=INK, fontweight='bold')

    # ---- bottom: the same weights as a bar chart ----
    axb.clear()
    axb.set_facecolor(PAPER)
    for spine in axb.spines.values():
        spine.set_visible(False)
    colors = [MOLE if i == focus else tint(weights[i]) for i in range(len(toks))]
    axb.bar(range(len(toks)), weights * reveal, color=colors, width=0.62,
            alpha=0.9)
    for i, w in enumerate(weights):
        axb.text(i, w * reveal + 0.02, f'{w:.2f}', ha='center', va='bottom',
                 fontsize=8, color=colors[i], alpha=reveal)
    axb.set_xticks(range(len(toks)), toks, fontsize=9, color=INK)
    axb.tick_params(length=0)
    axb.set_yticks([])
    axb.set_ylim(0, 0.6)
    axb.set_xlim(-0.6, len(toks) - 0.4)
    axb.text(-0.55, 0.5, 'attention weights (sum to 1)', fontsize=8.5,
             color=MUTED, ha='left', va='center')
    return []


anim2 = FuncAnimation(fig, frame2, frames=GROW + FLOW + HOLD2, blit=False)
html2 = HTML(anim2.to_jshtml(fps=fps2)); plt.close(fig); html2

That is the entire shape of attention: **compute a relevance weight from a query word to every other word, then replace the focus word's vector with the weighted average of the others.**  Do this for every word as query, and you have transformed the whole sequence, each vector now informed by the ones that matter to it.  Do it again in the next layer, on the already-contextual vectors, and you refine further.

In this animation, the weights were set by hand.  The real mechanism computes them from the vectors themselves, via a comparison (a dot product) passed through a softmax so they are nonnegative and sum to one — and it also lets the network *learn* what "relevant" should mean rather than hard-coding it.  That machinery is  the subject of the next notebook.

In this animation cartoon the embedding of *mole* moves but leaves the context words fixed.  In a real layer, every embedding is updated.

## Stacking transformer layers

So far the movement has lived in an abstract "meaning space," detached from the boxes and arrows of an actual network.  Time to connect the two.  Recall the encoder diagram from notebook 1: input tokens along the bottom, one output vector per position along the top, and every output drawing on every input through attention.  That diagram showed a *single* attention layer.  The real model *stacks* them — notebook 1's had two — and stacking is exactly what lets the refinement happen in steps.

The animation below puts the architecture and the meaning space side by side to describe how meaning accrues as layers are stacked:

In [5]:
# Playback speed for this animation, in frames per second.
# LOWER = SLOWER.  Try 6 (slow) up to 20 (brisk).  Re-run the cell.
FPS = 10

toks = ['<cls>', 'the', 'mole', 'burrowed', 'garden']
FOCUS, CLS, n_pos, n_layers = 2, 0, 5, 2
wts = np.array([0.08, 0.06, 0.12, 0.40, 0.34]); wts = wts / wts.sum()
cls_wts = np.array([0.10, 0.08, 0.40, 0.22, 0.20])   # what <cls> draws on

regions = {'CHEMISTRY': np.array([2.6, 2.2]),
           'ANIMAL':    np.array([2.9, -2.3]),
           'ESPIONAGE': np.array([-2.8, 1.4])}
mole_traj = [np.array([0.1, 0.1]), np.array([1.5, -1.15]),
             np.array([2.2, -1.85])]
anchor = {'burrowed': np.array([1.3, -2.9]), 'garden': np.array([3.7, -2.0])}
XLIM_R, YLIM_R = (-4, 4.4), (-3.6, 3.9)
bgR = region_image(regions, XLIM_R, YLIM_R, sigma=1.0)
LAYER_NAMES = ['embeddings', 'attention\nlayer 1', 'attention\nlayer 2']

# timeline, in frames
INTRO, BUILD, HOLD, READ, END = 8, 20, 8, 24, 24   # END: final hold
per = BUILD + HOLD
total = INTRO + n_layers * per + READ + END


def stage_of(f):
    """(layers built, layer being built, progress in [0,1], phase name)."""
    if f < INTRO:
        return 0, None, f / INTRO, 'intro'
    g = f - INTRO
    if g >= n_layers * per:
        return n_layers, None, min((g - n_layers * per) / READ, 1), 'read'
    L, local = g // per + 1, g % per
    if local < BUILD:
        return L - 1, L, local / BUILD, 'build'
    return L, None, 1.0, 'hold'


def node_color(p):
    return CLS_COL if p == CLS else MOLE if p == FOCUS else '#c9c9c9'


figA, (axL, axR) = plt.subplots(1, 2, figsize=(11, 4.8), dpi=DPI,
                                gridspec_kw=dict(width_ratios=[1.35, 1]))
figA.patch.set_facecolor(PAPER)
figA.subplots_adjust(left=0.01, right=0.99, top=0.88, bottom=0.03, wspace=0.04)


def draw_arch(f):
    built, building, sub, phase = stage_of(f)

    # ---- left: architecture grid ----
    blank_axes(axL, (-1.9, n_pos - 0.4), (-0.75, 3.6))
    for L, name in enumerate(LAYER_NAMES):           # a band per layer
        axL.add_patch(FancyBboxPatch((-0.45, L - 0.28), n_pos - 0.1, 0.56,
                      boxstyle='round,pad=0,rounding_size=0.25',
                      facecolor='#f1efe9', edgecolor='none', zorder=0))
        axL.text(-1.85, L, name, va='center', ha='left', fontsize=8.5,
                 color=MUTED, linespacing=1.1)

    # edges into mole in layers already built: faint orange
    for L in range(1, built + 1):
        for p in range(n_pos):
            path = curved_path((p, L - 1), (FOCUS, L))
            axL.plot(path[:, 0], path[:, 1], color=MOLE,
                     lw=0.5 + 6 * wts[p], alpha=0.22, zorder=1)

    # the layer being built: every position attends to every position
    # (grey), and mole's incoming edges light up with flowing particles
    if building is not None:
        s = ease(sub)
        for p in range(n_pos):
            for q in range(n_pos):
                path = curved_path((p, building - 1), (q, building))
                axL.plot(path[:, 0], path[:, 1], color='0.55', lw=0.6,
                         alpha=0.10 * s, zorder=1)
        for p in range(n_pos):
            path = curved_path((p, building - 1), (FOCUS, building))
            n_show = max(2, int(s * len(path)))
            axL.plot(path[:n_show, 0], path[:n_show, 1], color=MOLE,
                     lw=0.6 + 9 * wts[p], alpha=0.75, zorder=2,
                     solid_capstyle='round')
            particles(axL, path[:n_show], 1 + round(8 * wts[p]),
                      (f % 12) / 12, MOLE, size=10 + 30 * wts[p], zorder=3)

    # read-out: <cls> gathers from the last layer, then feeds the classifier
    if phase == 'read':
        gather = ease(sub / 0.6)
        for p in range(n_pos):
            path = curved_path((p, n_layers - 1), (CLS, n_layers))
            axL.plot(path[:, 0], path[:, 1], color=CLS_COL,
                     lw=0.6 + 9 * cls_wts[p], alpha=0.7 * gather, zorder=2)
            if sub < 0.75:
                particles(axL, path, 1 + round(8 * cls_wts[p]),
                          (f % 12) / 12, CLS_COL, size=10 + 30 * cls_wts[p],
                          zorder=3)
        a = ease((sub - 0.55) / 0.45)
        if a > 0:
            axL.annotate('', xy=(CLS, 3.08), xytext=(CLS, n_layers + 0.2),
                         arrowprops=dict(arrowstyle='-|>', color=CLS_COL,
                                         lw=2, alpha=a))
            axL.add_patch(FancyBboxPatch((CLS - 0.65, 3.1), 1.3, 0.34,
                          boxstyle='round,pad=0.04,rounding_size=0.12',
                          facecolor=CLS_COL, edgecolor='none', alpha=a,
                          zorder=6))
            axL.text(CLS, 3.27, 'classifier', ha='center', va='center',
                     color='white', fontsize=9, fontweight='bold', alpha=a,
                     zorder=7)

    # nodes: a layer appears as it is built
    for L in range(n_layers + 1):
        if L == 0:
            vis = ease(sub) if phase == 'intro' else 1.0
        elif L <= built:
            vis = 1.0
        elif L == building:
            vis = ease(sub)
        else:
            vis = 0.0
        if vis <= 0:
            continue
        for p in range(n_pos):
            big = p in (CLS, FOCUS)
            if big:
                glow_dot(axL, (p, L), node_color(p), size=200, glow=0.7 * vis,
                         zorder=5)
            else:
                axL.scatter(p, L, s=130, color=node_color(p), alpha=vis,
                            edgecolor='white', linewidths=1.3, zorder=4)
        if L == 0:
            for p in range(n_pos):
                big = p in (CLS, FOCUS)
                axL.text(p, -0.5, toks[p], ha='center', fontsize=9,
                         alpha=vis, color=node_color(p) if big else INK,
                         fontweight='bold' if big else 'normal')
    axL.text(0.5, 1.02, 'the architecture: attention layers, stacked',
             transform=axL.transAxes, ha='center', va='bottom', fontsize=11,
             color=INK, fontweight='bold')

    # ---- right: meaning space ----
    blank_axes(axR, XLIM_R, YLIM_R)
    draw_regions(axR, regions, bgR, XLIM_R, YLIM_R, label_dy=1.05)
    for wd, ap in anchor.items():
        word_pill(axR, ap, wd, color=REGION_COLORS['ANIMAL'], fs=8.5)
    if phase == 'intro':
        pos, lab, moving = mole_traj[0], 'embedding (context-free)', False
    elif phase == 'build':
        a, b = mole_traj[building - 1], mole_traj[building]
        pos = a + ease(sub) * (b - a)
        lab, moving = f'attention layer {building} at work', True
    else:
        pos, lab, moving = mole_traj[built], f'after layer {built}', False
    upto = built if not moving else building - 1
    route = []
    for a, b in zip(mole_traj[:upto], mole_traj[1:upto + 1]):
        route += list(straight_path(a, b, 15))
    route += list(straight_path(mole_traj[upto], pos, 15))
    fading_trail(axR, route, MOLE)
    for k in range(1, upto + 1):                 # numbered layer waypoints
        axR.scatter(*mole_traj[k], s=90, color='white', edgecolor=MOLE,
                    linewidths=1.4, zorder=5)
        axR.text(*mole_traj[k], str(k), ha='center', va='center',
                 fontsize=6.5, color=MOLE, fontweight='bold', zorder=6)
    glow_dot(axR, pos, MOLE, size=300, glow=1.0 if moving else 0.6)
    axR.text(pos[0] - 0.55, pos[1] - 0.45, 'mole', ha='center', fontsize=11,
             fontweight='bold', color=MOLE, zorder=9)
    axR.text(0.5, 0.03, lab, transform=axR.transAxes, ha='center',
             fontsize=9.5, color=INK)
    axR.text(0.5, 1.02, "the same token's vector, refined",
             transform=axR.transAxes, ha='center', va='bottom', fontsize=11,
             color=INK, fontweight='bold')
    return []


animA = FuncAnimation(figA, draw_arch, frames=total, blit=False)
htmlA = HTML(animA.to_jshtml(fps=FPS)); plt.close(figA); htmlA

A few things to read from this animation:

* **A layer is a refinement step.**  Each attention layer reads the previous layer's vectors and outputs a new set — for *mole*, one hop closer to its contextual meaning.  Depth allows the network to iteratively refine its representation.
* **Every position moves, in parallel.**  We follow *mole* for concreteness, but the grid computes a new vector at *every* position at once — *the*, *garden*, and the rest are being refined by their own incoming attention (edges not drawn, to keep the picture legible).
* **The classifier reads `<cls>`.**  The final classifier uses only the refined embedding of the `<cls>` token.  Its vector was refined the same way *mole*'s was — by attending to the whole sentence.  So after multiple layers, it has pooled the evidence the decision needs.  That is why, back in notebook 1, we prepended `<cls>` and read the answer out of position 0.

The orange edges have thicknesses that represent the attention weights, and here they were chosen by hand.  Computing them from the vectors is the operation we build in the next notebook.

Recall the heatmaps we plotted in notebook 1: those *are* the weights of the second animation.  Row $i$ of a map is the set of pulls on word $i$ — how much it draws from each other word.  The `<cls>` row was the summary slot pulling hardest from the words most useful for the sentiment decision.  When we plotted that "not/bad" example and saw weight concentrate on "bad," we were watching exactly this weighted-pull mechanism decide what matters.

## Summary

* An embedding layer is a fixed lookup: a word gets the same vector in every context, which cannot capture words whose meaning depends on their neighbors.
* Attention produces *contextual* representations: each layer moves a token's vector toward the meaning implied by the tokens around it, and stacking layers refines the result.
* The move is a **weighted average of the other tokens' vectors**, with weights that measure relevance — large for the tokens that matter.
* The attention maps of notebook 1 are these weights.  The only missing piece is how the weights are computed and learned — the operation we introduce next.